# Narrative Pattern Mining — Inspiration Knowledge Graph

Standalone pipeline: narrative chapters → 7-stage CoT extraction → LLM-native graph construction → DuckDB (VSS + FTS + PGQ).

| Stage | Purpose |
|-------|---------|
| Desloping | LLM quality filter — removes AI filler before extraction |
| Chunking | LangChain `RecursiveCharacterTextSplitter` — no heuristics |
| Extraction ×7 | Chain-of-thought + self-critique: visual · dialogue · power · dramatic · psychological · prose · emotional |
| Synthesis | Cross-chunk resonance, character signatures, generation seeds |
| Abstraction | Reusable narrative templates (abstraction_final) |
| Graph Construction | LLM-native node + edge inference → `LLMGraphOutput` |
| Storage | `extraction_chunks` + `inspiration_nodes` + `inspiration_edges` in DuckDB |
| Retrieval | HNSW (BGE-M3 1024-dim) + FTS (BM25) + duckpgq property graph |

**Standalone — no imports from `app/`**
**Prerequisites:** set `llm_api_key` in CONFIG or export `OPENAI_API_KEY`

In [11]:
%pip install -q "duckdb>=1.1.3" langchain langchain-openai langchain-core langchain-text-splitters \
    nest_asyncio tqdm pandas pyarrow pymupdf "pydantic>=2.0" tenacity "gradio_client>=0.9" httpx scikit-learn

Note: you may need to restart the kernel to use updated packages.


In [22]:
# ── Standard library ──────────────────────────────────────────────────────────
import asyncio
import json
import logging
import os
import re
from enum import Enum
from pathlib import Path
from typing import Any, Literal, Optional

# ── Third-party ───────────────────────────────────────────────────────────────
import duckdb
import nest_asyncio
import pandas as pd
from langchain_openai import ChatOpenAI
from pydantic import BaseModel, Field, ValidationError
from tenacity import retry, retry_if_exception_type, stop_after_attempt, wait_exponential
from tqdm.auto import tqdm

try:
    from sklearn.cluster import AgglomerativeClustering
except Exception:
    AgglomerativeClustering = None

nest_asyncio.apply()
logging.basicConfig(level=logging.WARNING)

# ── CONFIG ────────────────────────────────────────────────────────────────────
CONFIG: dict[str, Any] = {
    "embedding_model": "BAAI/bge-m3",
    "embedding_dim": 1024,
    "llm_model": "nousresearch/hermes-4-405b",
    "llm_base_url": "https://nano-gpt.com/api/subscription/chat/completions/v1",
    "llm_api_key": "SK-NANO-REDACTED", #DO NOT REMOVE
    "llm_temperature": 0.0,
    "db_path": str(Path("../narrative_bank.duckdb")),
    "parquet_dir": str(Path("../narrative_parquet")),
    "docs_dir": str(Path("../notebooks/notebookpdfs")),
    "chunk_size": 3000,
    "chunk_overlap": 300,
    "max_concurrent_llm": 3,
    "demo_mode": False,
    "demo_file": "01_The_Geology_of_Pain.md",
}

EMBED_DIM = CONFIG["embedding_dim"]
print(f"EMBED_DIM     : {EMBED_DIM}")
print(f"db_path       : {Path(CONFIG['db_path']).resolve()}")
print(f"docs_dir      : {Path(CONFIG['docs_dir']).resolve()}")

# =============================================================================
# PYDANTIC TYPE SYSTEM
# =============================================================================

class NodeType(str, Enum):
    TEMPLATE = "template"
    CHARACTER_SIGNATURE = "character_signature"
    DRAMATIC_PATTERN = "dramatic_pattern"
    POWER_DYNAMIC = "power_dynamic"
    VISUAL_MOTIF = "visual_motif"
    GENERATION_SEED = "generation_seed"
    RESONANCE_PATTERN = "resonance_pattern"


class EdgeType(str, Enum):
    REQUIRES = "requires"
    ENABLES = "enables"
    CONTAINS = "contains"
    RESONATES_WITH = "resonates_with"
    CONTRASTS_WITH = "contrasts_with"
    TRANSFORMS_TO = "transforms_to"
    COMBINES_WITH = "combines_with"
    INSTANTIATES = "instantiates"


class LLMGraphNode(BaseModel):
    node_id: str = Field(description="Unique short ID for this node")
    node_type: NodeType = Field(description="Type of narrative element")
    name: str = Field(description="Human-readable name")
    description: str = Field(default="", description="1-2 sentence description")
    properties: dict[str, Any] = Field(default_factory=dict, description="Type-specific properties")
    searchable_text: str = Field(default="", description="Concatenated text for FTS/embedding")
    confidence: float = Field(default=0.8, ge=0.0, le=1.0)


class LLMGraphEdge(BaseModel):
    source_node_id: str = Field(description="ID of source node")
    target_node_id: str = Field(description="ID of target node")
    edge_type: EdgeType = Field(description="Relationship type")
    weight: float = Field(default=0.8, ge=0.0, le=1.0)
    confidence: float = Field(default=0.8, ge=0.0, le=1.0)
    context: str = Field(default="", description="Why this relationship exists")


class EntityResolution(BaseModel):
    canonical_name: str = Field(description="Primary canonical name")
    aliases: list[str] = Field(default_factory=list)


class LLMGraphOutput(BaseModel):
    nodes: list[LLMGraphNode] = Field(default_factory=list)
    edges: list[LLMGraphEdge] = Field(default_factory=list)
    entity_resolutions: list[EntityResolution] = Field(default_factory=list)
    reasoning_trace: str = Field(default="")


class JudgeOutput(BaseModel):
    decision: Literal["accept", "reject"]
    reasoning: str = Field(description="Brief reason for the decision")
    quality_score: float = Field(default=0.5, ge=0.0, le=1.0)


class HumanizedDoc(BaseModel):
    title: str = Field(description="Document title")
    cleaned_text: str = Field(description="Text after stripping AI slop")
    is_slop: bool = Field(description="True if predominantly AI filler")
    quality_score: float = Field(ge=0.0, le=1.0)


class ChunkPreparationResult(BaseModel):
    decision: Literal["accept", "reject"]
    cleaned_text: str = Field(description="Chunk text after cleanup and humanization")
    quality_score: float = Field(default=0.5, ge=0.0, le=1.0)
    reasoning: str = Field(default="")


class NarrativeChunk(BaseModel):
    id: str
    text: str = Field(min_length=50)
    source_doc: str


class ExtractionPayloadBase(BaseModel):
    evidence: list[str] = Field(default_factory=list)
    reasoning_trace: dict[str, Any] = Field(default_factory=dict)
    confidence: float = Field(default=0.0, ge=0.0, le=1.0)
    notes: Optional[str] = Field(default=None)


class VisualAtmospherePayload(ExtractionPayloadBase):
    color_motifs: list[dict[str, Any]] = Field(default_factory=list)
    lighting_quality: list[dict[str, Any]] = Field(default_factory=list)
    scent_signatures: list[dict[str, Any]] = Field(default_factory=list)
    sound_texture: list[dict[str, Any]] = Field(default_factory=list)
    spatial_dynamics: list[dict[str, Any]] = Field(default_factory=list)
    temperature_quality: list[dict[str, Any]] = Field(default_factory=list)
    texture_vocabulary: list[dict[str, Any]] = Field(default_factory=list)
    environmental_mood: str = Field(default="")


class DialogueStylePayload(ExtractionPayloadBase):
    speakers: list[dict[str, Any]] = Field(default_factory=list)
    dialogue_dynamics: dict[str, Any] = Field(default_factory=dict)


class PsychologicalProfilePayload(ExtractionPayloadBase):
    characters: list[dict[str, Any]] = Field(default_factory=list)


class PowerDynamicsPayload(ExtractionPayloadBase):
    dynamics: list[dict[str, Any]] = Field(default_factory=list)


class DramaticStructurePayload(ExtractionPayloadBase):
    structures: list[dict[str, Any]] = Field(default_factory=list)


class ProseTexturePayload(ExtractionPayloadBase):
    sentence_rhythm: dict[str, Any] = Field(default_factory=dict)
    metaphor_analysis: dict[str, Any] = Field(default_factory=dict)
    sensory_frequency: dict[str, Any] = Field(default_factory=dict)
    repetition_patterns: list[dict[str, Any]] = Field(default_factory=list)
    body_focus: dict[str, Any] = Field(default_factory=dict)
    gaze_tracking: dict[str, Any] = Field(default_factory=dict)


class EmotionalResonancePayload(ExtractionPayloadBase):
    primary_emotions: list[dict[str, Any]] = Field(default_factory=list)
    secondary_emotions: list[dict[str, Any]] = Field(default_factory=list)
    discomfort_indicators: list[dict[str, Any]] = Field(default_factory=list)
    arousal_points: list[dict[str, Any]] = Field(default_factory=list)
    dread_cultivation: dict[str, Any] = Field(default_factory=dict)
    hope_dynamics: dict[str, Any] = Field(default_factory=dict)
    reader_investment: dict[str, Any] = Field(default_factory=dict)


class CrossReferenceSynthesisPayload(ExtractionPayloadBase):
    resonance_patterns: list[dict[str, Any]] = Field(default_factory=list)
    character_signatures: list[dict[str, Any]] = Field(default_factory=list)
    scene_composition: list[dict[str, Any]] = Field(default_factory=list)
    abstractable_patterns: list[dict[str, Any]] = Field(default_factory=list)
    generation_seeds: list[dict[str, Any]] = Field(default_factory=list)


class AbstractionFinalPayload(ExtractionPayloadBase):
    templates: list[dict[str, Any]] = Field(default_factory=list)


STAGE_MODELS: dict[str, type[BaseModel]] = {
    "visual_atmosphere": VisualAtmospherePayload,
    "dialogue_style": DialogueStylePayload,
    "psychological_profile": PsychologicalProfilePayload,
    "power_dynamics": PowerDynamicsPayload,
    "dramatic_structure": DramaticStructurePayload,
    "prose_texture": ProseTexturePayload,
    "emotional_resonance": EmotionalResonancePayload,
    "cross_reference_synthesis": CrossReferenceSynthesisPayload,
    "abstraction_final": AbstractionFinalPayload,
}


def _stage_model(stage_key: str) -> type[BaseModel]:
    stage_model = STAGE_MODELS.get(stage_key)
    if stage_model is None:
        raise KeyError(f"Unknown stage: {stage_key!r}")
    return stage_model


def _empty_stage_payload(stage_key: str) -> dict[str, Any]:
    return _stage_model(stage_key)().model_dump(mode="json")


def _structured_dump(result: Any) -> dict[str, Any]:
    if isinstance(result, BaseModel):
        return result.model_dump(mode="json")
    if isinstance(result, dict):
        return result
    if hasattr(result, "model_dump"):
        return result.model_dump(mode="json")
    return {"notes": str(result)}


class HFSpaceConfig(BaseModel):
    space_url: str = "https://chmielvu-multilingual-nlp.hf.space/embeddings"
    embedding_model: str = "multilingual-embed"
    embedding_dim: int = 1024
    timeout_sec: int = 60


class HFSpaceEmbeddings:
    def __init__(self, config: HFSpaceConfig | None = None) -> None:
        self.config = config or HFSpaceConfig()
        self._client: Any = None

    @property
    def client(self) -> Any:
        if self._client is None:
            from gradio_client import Client
            self._client = Client(self.config.space_url)
        return self._client

    def embed(self, texts: list[str]) -> list[list[float]]:
        if not texts:
            return []
        result = self.client.predict(
            model=self.config.embedding_model,
            input=texts,
            api_name="/embeddings",
        )
        if isinstance(result, dict) and "embeddings" in result:
            return result["embeddings"]
        if isinstance(result, list):
            return result
        raise ValueError(f"Unexpected embedding response type: {type(result)}")

    def embed_single(self, text: str) -> list[float]:
        embs = self.embed([text])
        return embs[0] if embs else [0.0] * self.config.embedding_dim


embedder = HFSpaceEmbeddings()
print(f"✓ HFSpaceEmbeddings ready  dim={embedder.config.embedding_dim}")
print("✓ Types and utilities defined")

EMBED_DIM     : 1024
db_path       : /mnt/c/Users/Jan/Documents/GitHub/work/docs/narrative_bank.duckdb
docs_dir      : /mnt/c/Users/Jan/Documents/GitHub/work/docs/notebooks/notebookpdfs
✓ HFSpaceEmbeddings ready  dim=1024
✓ Types and utilities defined


In [13]:
# ── DuckDB: connect + extensions ──────────────────────────────────────────────
db_path = Path(CONFIG["db_path"]).resolve()
db_path.parent.mkdir(parents=True, exist_ok=True)

con = duckdb.connect(str(db_path))
print(f"Connected → {db_path}")

for ext in ["fts", "vss"]:
    con.sql(f"INSTALL {ext}; LOAD {ext};")
    print(f"  ✓ {ext}")

con.sql("SET GLOBAL hnsw_enable_experimental_persistence = true;")
print("  ✓ hnsw persistence enabled")

try:
    con.sql("INSTALL duckpgq FROM community; LOAD duckpgq;")
    PGQ_AVAILABLE = True
    print("  ✓ duckpgq")
except Exception as _pgq_err:
    PGQ_AVAILABLE = False
    print(f"  ✗ duckpgq skipped ({_pgq_err})")

Connected → /mnt/c/Users/Jan/Documents/GitHub/work/docs/narrative_bank.duckdb
  ✓ fts
  ✓ vss
  ✓ hnsw persistence enabled
  ✓ duckpgq


In [14]:
# ── Schema ────────────────────────────────────────────────────────────────────
# extraction_chunks  — raw 7-stage outputs, judge decision, quality score
# inspiration_nodes  — graph nodes: templates, patterns, characters, seeds, etc.
# inspiration_edges  — relationships between nodes

con.sql("""
    CREATE TABLE IF NOT EXISTS extraction_chunks (
        chunk_id                 TEXT PRIMARY KEY,
        source_doc               TEXT NOT NULL,
        text                     TEXT NOT NULL,
        visual_atmosphere        JSON,
        dialogue_style           JSON,
        psychological_profile    JSON,
        power_dynamics           JSON,
        dramatic_structure       JSON,
        prose_texture            JSON,
        emotional_resonance      JSON,
        cross_reference_synthesis JSON,
        judge_decision           TEXT,
        judge_reasoning          TEXT,
        quality_score            FLOAT DEFAULT 0.0
    );
""")

con.sql(f"""
    CREATE TABLE IF NOT EXISTS inspiration_nodes (
        node_id          TEXT PRIMARY KEY,
        node_type        TEXT    NOT NULL,
        name             TEXT    NOT NULL,
        description      TEXT,
        searchable_text  TEXT,
        embedding        FLOAT[{EMBED_DIM}],
        properties       JSON,
        pattern_type     TEXT,
        confidence       FLOAT   DEFAULT 0.0,
        source_chunk_ids JSON
    );
""")

con.sql("""
    CREATE TABLE IF NOT EXISTS inspiration_edges (
        edge_id        TEXT PRIMARY KEY,
        source_node_id TEXT NOT NULL,
        target_node_id TEXT NOT NULL,
        edge_type      TEXT NOT NULL,
        weight         FLOAT DEFAULT 1.0,
        confidence     FLOAT DEFAULT 1.0,
        context        TEXT,
        FOREIGN KEY (source_node_id) REFERENCES inspiration_nodes(node_id),
        FOREIGN KEY (target_node_id) REFERENCES inspiration_nodes(node_id)
    );
""")

for _idx in [
    "CREATE INDEX IF NOT EXISTS idx_inodes_type     ON inspiration_nodes(node_type);",
    "CREATE INDEX IF NOT EXISTS idx_inodes_pattern  ON inspiration_nodes(pattern_type);",
    "CREATE INDEX IF NOT EXISTS idx_iedges_src      ON inspiration_edges(source_node_id);",
    "CREATE INDEX IF NOT EXISTS idx_iedges_tgt      ON inspiration_edges(target_node_id);",
    "CREATE INDEX IF NOT EXISTS idx_iedges_type     ON inspiration_edges(edge_type);",
    "CREATE INDEX IF NOT EXISTS idx_chunks_doc      ON extraction_chunks(source_doc);",
    "CREATE INDEX IF NOT EXISTS idx_chunks_judge    ON extraction_chunks(judge_decision);",
]:
    con.sql(_idx)

print("✓ Schema ready")
con.sql("SHOW TABLES").show()

✓ Schema ready
┌───────────────────┐
│       name        │
│      varchar      │
├───────────────────┤
│ extraction_chunks │
│ inspiration_edges │
│ inspiration_nodes │
└───────────────────┘



In [15]:
# ── Document loader ───────────────────────────────────────────────────────────
import fitz  # PyMuPDF
from typing import Any, Dict, List, Optional, Tuple


def load_documents(
    docs_dir: str,
    demo_mode: bool = False,
    demo_file: Optional[str] = None,
) -> List[Dict[str, Any]]:
    p = Path(docs_dir)
    if not p.exists():
        raise FileNotFoundError(f"Docs dir not found: {p.resolve()}")

    files = sorted(f for f in p.iterdir() if f.suffix.lower() in {".md", ".pdf"})
    if not files:
        raise FileNotFoundError(f"No .md/.pdf files in {p.resolve()}")

    if demo_mode:
        targets = [f for f in files if f.name == demo_file] if demo_file else []
        files = targets or [files[0]]

    docs: List[Dict[str, Any]] = []
    for f in files:
        try:
            if f.suffix.lower() == ".pdf":
                with fitz.open(str(f)) as pdf:
                    text = "".join(page.get_text() for page in pdf)
            else:
                text = f.read_text(encoding="utf-8")
        except Exception as e:
            print(f"  ✗ Error reading {f.name}: {e}")
            continue

        docs.append({
            "name": f.stem,
            "filename": f.name,
            "path": str(f),
            "text": text,
            "char_count": len(text),
        })
        print(f"  {f.name}  ({len(text):,} chars)")

    return docs


docs = load_documents(
    CONFIG["docs_dir"],
    demo_mode=CONFIG["demo_mode"],
    demo_file=CONFIG["demo_file"],
)
print(f"\n✓ {len(docs)} document(s) loaded")

  Blank 4.pdf  (51,093 chars)

✓ 1 document(s) loaded


In [16]:
# ── Desloping pass ────────────────────────────────────────────────────────────
# Filters AI-generated filler before chunking. Uses structured output.

_DESLOP_PROMPT = """
You are a Narrative Quality Controller performing "Desloping": identifying and removing AI-generated filler.

PATTERNS TO ELIMINATE:
- "In the realm of", "It is important to note", "Furthermore", "Delve into"
- Circular summaries repeating the same point 3+ times
- Generic disclaimers, vague high-level concepts lacking concrete plot/character development
- Excessive flowery adjectives masking no actual dramatic content

TASK:
1. Analyse the document below.
2. If it is high-density narrative (specific names, concrete actions, unique sensory details), preserve the core.
3. If mostly AI slop, flag it and condense to what factual content exists.
4. Return structured JSON.

TITLE: {title}
CONTENT:
{content}
"""


def _init_llm() -> ChatOpenAI:
    api_key: Optional[str] = CONFIG.get("llm_api_key") or os.environ.get("OPENAI_API_KEY")  # type: ignore[assignment]
    kwargs: Dict[str, Any] = {
        "model":       CONFIG["llm_model"],
        "temperature": CONFIG["llm_temperature"],
        "base_url":    CONFIG["llm_base_url"],
    }
    if api_key:
        kwargs["api_key"] = api_key
    return ChatOpenAI(**kwargs)


def deslop_documents(docs: List[Dict[str, Any]]) -> List[Dict[str, Any]]:
    llm = _init_llm().with_structured_output(HumanizedDoc)
    refined: List[Dict[str, Any]] = []

    print(f"Desloping {len(docs)} document(s)...")
    for doc in tqdm(docs):
        prompt = _DESLOP_PROMPT.format(title=doc["name"], content=doc["text"][:12000])
        try:
            result = llm.invoke(prompt)
            desloped = _structured_dump(result)
        except Exception as e:
            print(f"  ✗ Desloping failed for {doc['filename']}: {e}")
            desloped = {"cleaned_text": doc["text"], "is_slop": False, "quality_score": 0.5}

        if (not desloped.get("is_slop")) or desloped.get("quality_score", 0) > 0.3:
            refined.append({
                **doc,
                "text":    desloped.get("cleaned_text", doc["text"]),
                "is_slop": desloped.get("is_slop", False),
                "quality": desloped.get("quality_score", 0.5),
            })

    print(f"✓ {len(refined)}/{len(docs)} docs passed quality filter")
    return refined


desloped_docs = deslop_documents(docs)

Desloping 1 document(s)...


100%|██████████| 1/1 [00:00<00:00,  1.08it/s]

  ✗ Desloping failed for Blank 4.pdf: <!DOCTYPE html><html lang="en"><head><meta charSet="utf-8"/><meta name="viewport" content="minimum-scale=1, initial-scale=1, width=device-width, viewport-fit=cover"/><meta name="viewport" content="width=device-width, initial-scale=1"/><link rel="stylesheet" href="/_next/static/css/2061f151a632d52b.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/4aa34f00c9a735eb.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/8bd2226ccc3cc522.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/68fd0b07afc3d15d.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/c6f80ce875958cc8.css" data-precedence="next"/><link rel="preload" as="script" fetchPriority="low" href="/_next/static/chunks/webpack-eb1a8bf6a10b768e.js"/><script src="/_next/static/chunks/c6e29eda-25a621f962ffa7a1.js" async=""></script><script src="/_next/static/chunks/38260-54573970784b7f1a.js" async=""><

In [17]:
# ── Chunking ──────────────────────────────────────────────────────────────────
from langchain_text_splitters import RecursiveCharacterTextSplitter

_splitter = RecursiveCharacterTextSplitter(
    chunk_size=CONFIG["chunk_size"],
    chunk_overlap=CONFIG["chunk_overlap"],
    separators=["\n\n", "\n", ".", "!", "?", " "],
)


def _split_document_sections(text: str) -> list[str]:
    section_break = re.compile(
        r"^\s{0,3}#{1,6}\s+.+$|^\s*Chapter\s+.+$|^\s*[IVXLC]+\s*$",
        re.IGNORECASE,
    )
    sections: list[str] = []
    current_lines: list[str] = []

    for line in text.splitlines():
        stripped = line.strip()
        if section_break.match(stripped) and current_lines:
            section = "\n".join(current_lines).strip()
            if section:
                sections.append(section)
            current_lines = [line]
            continue
        current_lines.append(line)

    tail = "\n".join(current_lines).strip()
    if tail:
        sections.append(tail)

    return sections or [text.strip()]


def _structure_aware_chunks(doc: dict[str, Any]) -> list[dict[str, str]]:
    chunks: list[dict[str, str]] = []
    for section in _split_document_sections(doc["text"]):
        for chunk_text in _splitter.split_text(section):
            normalized = re.sub(r"\n{3,}", "\n\n", chunk_text).strip()
            if normalized:
                chunks.append(
                    {
                        "text": normalized,
                        "source_doc": doc["filename"],
                    }
                )
    return chunks


raw_chunks: list[dict[str, Any]] = []
for doc in desloped_docs:
    for idx, item in enumerate(_structure_aware_chunks(doc)):
        raw_chunks.append(
            {
                "id": f"{doc['name']}_{idx:04d}",
                "text": item["text"],
                "source_doc": item["source_doc"],
            }
        )

# Validate with Pydantic — drops chunks < 50 chars
validated_chunks: list[NarrativeChunk] = []
for chunk_data in raw_chunks:
    try:
        validated_chunks.append(NarrativeChunk.model_validate(chunk_data))
    except ValidationError:
        pass

print(f"✓ {len(validated_chunks)} valid chunks from {len(desloped_docs)} doc(s)")

✓ 19 valid chunks from 1 doc(s)


In [18]:
# =============================================================================
# EXTRACTION PROMPTS — Chain-of-Thought + Self-Critique for all 9 stages
# =============================================================================

PROMPT_GUARDRAILS = """
GLOBAL OUTPUT RULES:
- Prefer concrete, text-grounded claims over abstract interpretation.
- If evidence is weak, return empty arrays or lower confidence instead of inventing detail.
- Use the provided schema exactly; do not add extra top-level fields.
- Avoid generic slop phrases like "palpable tension", "intricate tapestry", "in the realm of", "delve into".
- When asked to infer a pattern, cite the exact phrase or event that supports it.

CONTRASTIVE MINI-EXAMPLE:
BAD: "The scene feels tense and symbolic."
GOOD: "The scene uses a locked door, a lowered gaze, and clipped sentences to signal coercion."
"""

EXTRACTION_PROMPTS: Dict[str, str] = {}

# ── Stage 1: Visual Atmosphere ────────────────────────────────────────────────
EXTRACTION_PROMPTS["visual_atmosphere"] = """
You are extracting visual, sensory, and atmospheric elements for narrative generation.

## Chain-of-Thought Process

**Step 1: Color Survey**
Scan for color words explicitly stated OR strongly implied through objects. For each:
- What object or space carries this color?
- What emotion or quality does it carry?
- Is it tied to a specific character or location?

**Step 2: Lighting Analysis**
Identify all references to light, darkness, or visibility:
- What adjectives describe light quality? (harsh, diffuse, flickering, clinical)
- How does lighting affect emotional atmosphere?

**Step 3: Sensory Mapping**
For each modality present:
- SCENT: What smells? Associated with whom or where?
- SOUND: What auditory textures? Recurring motifs?
- TOUCH/TEXTURE: What tactile words? (velvet, steel, skin, stone)
- TEMPERATURE: Heat, cold, emotional resonance

**Step 4: Spatial Dynamics**
- Who stands? Who sits? Who moves?
- What distances/barriers separate characters?
- What does positioning reveal about power?

**Step 5: Synthesis**
Combine into an overall atmospheric quality.

## Self-Critique Checklist
1. Each extraction includes a quoted phrase from the text
2. Specificity: "oppressive violet light" not just "lighting"
3. If no scent is mentioned, return empty array — do NOT invent

## Output Format
Return JSON matching the schema with:
- color_motifs, lighting_quality, scent_signatures, sound_texture,
  spatial_dynamics, temperature_quality, texture_vocabulary,
  environmental_mood, evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 2: Dialogue Style ───────────────────────────────────────────────────
EXTRACTION_PROMPTS["dialogue_style"] = """
You are analyzing character voice patterns for narrative generation.

## Chain-of-Thought Process

**Step 1: Speaker Identification**
List every character who speaks. Count their total lines.

**Step 2: Sentence Structure Analysis**
For each speaker:
- Average sentence length (short <10w, medium 10-20w, long >20w)
- Fragment frequency, question vs statement ratio
- Use of pauses (ellipses, dashes)

**Step 3: Vocabulary Register**
- Formal/Clinical/Poetic/Profane/Archaic/Modern
- Signature words they use repeatedly
- Words they NEVER use

**Step 4: Subtext Density**
For key exchanges — what is said vs what is meant?

**Step 5: Power Dynamics in Speech**
- Who asks questions vs who answers?
- How is silence used strategically?

## Self-Critique Checklist
1. Every speech pattern claim includes a direct quote
2. Patterns are RECURRING not one-off moments
3. Each character's voice is distinctively described

## Output Format
Return JSON with:
- speakers (list with name, sentence_structure, vocabulary_register,
  punctuation_patterns, command_style, silence_usage, subtext_density,
  subtext_examples, cruelty_wrapping, signature_phrases, confidence, ambiguities)
- dialogue_dynamics
- evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 3: Psychological Profile ───────────────────────────────────────────
EXTRACTION_PROMPTS["psychological_profile"] = """
You are analyzing character psychology for narrative generation.

## Chain-of-Thought Process

**Step 1: Behavioral Evidence Collection**
For each character, collect BEHAVIORS (not thoughts/feelings):
- Actions taken, things they say about themselves, physical reactions under stress

**Step 2: Core Drive Inference**
From behaviors: What does this character pursue above all else?
What would they sacrifice for? What would they never sacrifice?

**Step 3: Contradiction Mapping**
- What they want vs what they pursue
- What they believe vs what they do
- What they show vs what they feel

**Step 4: Defense Mechanism Detection**
Under stress: intellectualization, projection, denial, displacement, splitting, repression?

**Step 5: Breaking Sequence Hypothesis**
If pushed to psychological collapse:
- What would be first defense to fail and what triggers it?
- What would collapse look like?

## Self-Critique Checklist
1. Every psychological claim traces to specific behavior in text
2. "Creates hierarchical distance" not "arrogant"
3. Note confidence and whether claim is observed or inferred

## Output Format
Return JSON with:
- characters (list with name, core_drive, contradictions, defense_mechanisms,
  power_expression, vulnerability_points, relationship_to_pain,
  relationship_to_pleasure, breaking_sequence, confidence, ambiguities)
- evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 4: Power Dynamics ───────────────────────────────────────────────────
EXTRACTION_PROMPTS["power_dynamics"] = """
You are analyzing power relationships for narrative generation.

## Chain-of-Thought Process

**Step 1: Power Mapping**
- Who has formal authority? Informal influence? Physical dominance?

**Step 2: Dynamic Classification**
- COERCED: enforced through threat
- RITUALIZED: formalized through protocol
- CONTESTED: actively resisted
- INTERNALIZED: subordinate accepts hierarchy

**Step 3: Mechanism Analysis**
- How is power exerted? (commands, manipulation, violence)
- How is it enforced? (surveillance, punishment, reward)
- How is it resisted? (open defiance, subversion, withdrawal)

**Step 4: Complicity Extraction**
How are subordinates made to participate in their own subjugation?
- Forced confession? Made to ask for what is done to them?
- Made to harm others? Made to acknowledge enjoyment?

## Self-Critique Checklist
1. Document actual power displays, not assumed
2. Show resistance where it exists
3. "Withholds eye contact" not "uses silence"

## Output Format
Return JSON with:
- dynamics (list with dominant_party, subordinate_party, dynamic_type,
  enforcement_mechanisms, submission_markers, resistance_forms,
  complicity_extraction, ritual_elements, intensity_trend, confidence)
- evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 5: Dramatic Structure ───────────────────────────────────────────────
EXTRACTION_PROMPTS["dramatic_structure"] = """
You are identifying dramatic patterns for narrative template generation.

## Chain-of-Thought Process

**Step 1: Scene Phase Segmentation**
Break the scene into ordered phases — what initiates it, what phases it passes through, how it resolves.

**Step 2: Structure Type Recognition**
Classify:
- HUMILIATION_RITUAL: systematic reduction of status
- BREAKING_SEQUENCE: progressive psychological dismantling
- FORCED_REVELATION: extraction of hidden information
- HOPE_DESTRUCTION: setup then elimination of escape
- POWER_DEMONSTRATION: display of dominance
- COMPLICITY_FORCING: making subordinate participate in subjugation

**Step 3: Tension Curve**
Rate intensity (0.0-1.0) per phase. Where is the peak? What creates it?

**Step 4: Reusable Element Extraction**
What conditions trigger this pattern? Essential vs optional elements?
What makes it template-replicable?

## Self-Critique Checklist
1. Ordered sequence, not plot summary
2. Justify each intensity rating
3. Template utility: could another writer use this?

## Output Format
Return JSON with:
- structures (list with structure_type, trigger_condition, phase_sequence,
  tension_curve, witness_function, reusable_elements, confidence)
- evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 6: Prose Texture ────────────────────────────────────────────────────
EXTRACTION_PROMPTS["prose_texture"] = """
You are analyzing prose style for narrative generation.

## Chain-of-Thought Process

**Step 1: Sentence Rhythm Analysis**
Sample 5-10 sentences:
- Calculate average length
- Identify variation pattern
- Note where pacing accelerates/decelerates and what triggers it

**Step 2: Metaphor and Imagery Census**
- Count metaphor/simile instances
- Classify domains: nature, violence, domestic, clinical, architectural
- Identify recurring image patterns

**Step 3: Sensory Detail Frequency**
Count mentions by sense: visual, auditory, olfactory, tactile, gustatory, internal

**Step 4: Repetition Pattern Detection**
- What words/phrases repeat?
- Function: emphasis, ritual, obsession?

**Step 5: Body Focus Mapping**
Which body parts receive attention? Eyes, hands, mouths, skin?
What does this focus signify?

## Self-Critique Checklist
1. Include counts and averages — quantitative grounding
2. "Fragments create staccato urgency" not "short sentences"
3. Multiple quotes showing each pattern

## Output Format
Return JSON with:
- sentence_rhythm, metaphor_analysis, sensory_frequency,
  repetition_patterns, body_focus, gaze_tracking,
  evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Stage 7: Emotional Resonance ──────────────────────────────────────────────
EXTRACTION_PROMPTS["emotional_resonance"] = """
You are mapping predicted reader emotional response for narrative generation.

## Chain-of-Thought Process

**Step 1: Primary Emotion Identification**
What emotions does this scene PRIMARILY evoke?
- Name specifically (not "fear" but "anticipatory dread")
- Rate intensity 0.0-1.0
- Identify the specific textual trigger

**Step 2: Secondary Emotion Layering**
Background emotional coloring — lower intensity but persistent.

**Step 3: Discomfort Analysis**
What creates reader discomfort? Be specific about the mechanism:
- Physical descriptions? Psychological manipulation? Forced participation?

**Step 4: Engagement Mechanics**
What makes the reader need to continue?
- Unresolved tension? Character investment? Threat anticipation?

**Step 5: Dread and Hope Dynamics**
- How is dread cultivated?
- Is hope offered? How is it extinguished?

## Self-Critique Checklist
1. Reader-focused: what the reader FEELS, not what characters feel
2. HOW the text creates the emotion — mechanism not label
3. Acknowledge: different readers may respond differently

## Output Format
Return JSON with:
- primary_emotions, secondary_emotions, discomfort_indicators,
  arousal_points, dread_cultivation, hope_dynamics, reader_investment,
  evidence, reasoning_trace, confidence

TEXT:
{text}
"""

# ── Synthesis ─────────────────────────────────────────────────────────────────
EXTRACTION_PROMPTS["cross_reference_synthesis"] = """
You have 7-stage extractions from narrative chunks. Synthesize cross-cutting patterns.

## Chain-of-Thought Process

**Step 1: Resonance Detection**
Where do different layers reinforce each other?
Example: dialogue style (clinical vocabulary) + visual motif (sterile lighting) = theme of cold control

**Step 2: Character Signature Assembly**
For each character, combine: dialogue, psychology, visual associations, power role.
What makes each distinctively identifiable across all layers?

**Step 3: Scene Composition Recipe**
How do visual, atmospheric, emotional, and dramatic elements combine?
What is the recipe for this type of scene?

**Step 4: Abstractable Pattern Identification**
What patterns emerge that could become reusable templates?
Conditions under which they apply?

**Step 5: Generation Seed Creation**
Create 3-5 concrete seeds for procedural generation:
Each: pattern_type, required_elements, emotional_target, example_instantiation

## Self-Critique
- Are resonance patterns specific or generic?
- Are character signatures distinct from each other?
- Are generation seeds actionable?

## Output Format
Return JSON with:
- resonance_patterns, character_signatures, scene_composition,
  abstractable_patterns, generation_seeds, evidence, reasoning_trace, confidence

EXTRACTIONS:
{extractions}
"""

# ── Abstraction ───────────────────────────────────────────────────────────────
EXTRACTION_PROMPTS["abstraction_final"] = """
You have cross-reference synthesis data. Create fully abstracted, reusable narrative templates.

## Chain-of-Thought Process

**Step 1: Name Removal**
Strip all specific character names, locations, plot details.

**Step 2: Structural Core Retention**
Retain: dramatic arc shape, psychological dynamics, sensory qualities,
power mechanic, dialogue style patterns.

**Step 3: Parameter Specification**
For each template define:
- trigger_conditions: what conditions initiate this pattern?
- required_archetypes: what character types are needed?
- emotional_target: what reader emotion does it serve?
- visual_requirements: what motifs does it require?
- phase_structure: ordered phases with functions

**Step 4: Usage Guidelines**
- How to instantiate this pattern?
- What variations are possible?
- What makes it succeed or fail?

## Self-Critique
- Can another writer use this template without seeing the source text?
- Are archetypes abstract enough to be reusable?
- Is the example instantiation actually different from the source?

## Output Format
Each template must have:
template_id, template_name, pattern_type, trigger_conditions,
required_archetypes, emotional_target, visual_requirements,
phase_structure, dialogue_guidelines, example_instantiation

Return JSON with: templates, evidence, reasoning_trace, confidence

SOURCE PATTERNS:
{patterns}
"""

# ── Graph Construction ────────────────────────────────────────────────────────
GRAPH_CONSTRUCTION_PROMPT = """
You are constructing an Inspiration Knowledge Graph from narrative extraction data.

## Your Task
Transform synthesis + abstraction data into NODES and EDGES for a knowledge graph.

## Node Types
- TEMPLATE: Reusable narrative templates (from abstraction_final.templates)
- CHARACTER_SIGNATURE: Character profiles with voice, psychology, power role
- DRAMATIC_PATTERN: Recurring dramatic structures (humiliation_ritual, etc.)
- POWER_DYNAMIC: Specific power relationships between parties
- VISUAL_MOTIF: Recurring visual/atmospheric elements
- GENERATION_SEED: Concrete inspiration seeds for procedural generation
- RESONANCE_PATTERN: Cross-layer thematic resonances

## Edge Types
- REQUIRES: A requires B to function
- ENABLES: A enables B to occur
- RESONATES_WITH: A reinforces B thematically
- CONTRASTS_WITH: A opposes B thematically
- INSTANTIATES: A is an instance of abstract pattern B
- TRANSFORMS_TO: A can transform into B
- COMBINES_WITH: A and B can combine into something new

## Process
1. **Node Identification**: Which elements become nodes? Extract from:
   - abstraction_final.templates → TEMPLATE
   - character_signatures → CHARACTER_SIGNATURE
   - dramatic structures → DRAMATIC_PATTERN
   - power dynamics → POWER_DYNAMIC
   - color/visual motifs → VISUAL_MOTIF
   - generation seeds → GENERATION_SEED
   - resonance patterns → RESONANCE_PATTERN

2. **Property Extraction**: For each node, extract type-specific properties.

3. **Relationship Inference**:
   - Which CHARACTER_SIGNATURE ENABLES which POWER_DYNAMIC?
   - Which DRAMATIC_PATTERN does each TEMPLATE INSTANTIATE?
   - Which VISUAL_MOTIF RESONATES_WITH which CHARACTER_SIGNATURE?
   - Which templates COMBINE_WITH or TRANSFORM_TO others?

4. **Entity Resolution**: If the same entity appears under different names,
   identify canonical name and list aliases.

5. **Searchable Text**: For each node, build concatenated searchable_text
   from name + description + key properties.

## Output Format
Return a LLMGraphOutput with:
- nodes: List[LLMGraphNode] (node_id, node_type, name, description, properties, searchable_text, confidence)
- edges: List[LLMGraphEdge] (source_node_id, target_node_id, edge_type, weight, confidence, context)
- entity_resolutions: List[EntityResolution] (canonical_name, aliases)
- reasoning_trace: string explaining your graph construction decisions

## Important
- node_id must be a short unique string (use slugified name)
- Every edge must reference valid node_ids from the nodes list
- Prefer quality over quantity: 10 strong edges beat 50 weak ones
- Prefer explicit confidence when unsure rather than inventing more edges

SYNTHESIS + ABSTRACTION DATA:
{synthesis_json}
"""

print(f"✓ {len(EXTRACTION_PROMPTS)} extraction prompts  +  1 graph construction prompt defined")

✓ 9 extraction prompts  +  1 graph construction prompt defined


In [19]:
# ── Async extraction pipeline ─────────────────────────────────────────────────

EXTRACTION_STAGE_ORDER = [
    "visual_atmosphere",
    "dialogue_style",
    "power_dynamics",
    "dramatic_structure",
    "psychological_profile",
    "prose_texture",
    "emotional_resonance",
]

_CHUNK_GATE_PROMPT = """
You are a ruthless editorial constraint engine preparing a narrative chunk for extraction.

TASK:
1. Reject chunks that are mostly boilerplate, noise, broken formatting, or too fragmentary to support reliable extraction.
2. If the chunk has usable narrative material, humanize it only enough to improve readability:
   - remove filler and repetition
   - keep the original facts, names, actions, and sensory details
   - keep the tone grounded in the source
   - avoid generic literary filler or over-polished paraphrase
   - vary sentence length, but do not add new events
3. Return structured output.

CONSTRAINTS:
- Do not introduce metaphors or abstractions not present in the text.
- Do not replace concrete nouns with vague summary language.
- Prefer short, direct sentences when the source is terse.
- If the chunk becomes materially shorter than the source, preserve the lost factual detail.

GOOD:
Source: "He looked at the door. The lock was bent."
Cleaned: "He looked at the door. The lock was bent."

BAD:
Source: "He looked at the door. The lock was bent."
Cleaned: "He stood before the threshold, sensing an ominous impediment."

Return:
- decision: accept or reject
- cleaned_text: the text to send into extraction if accepted
- quality_score: 0.0-1.0
- reasoning: brief explanation

CHUNK:
{chunk_text}
"""


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _invoke_chunk_gate(llm: ChatOpenAI, chunk: NarrativeChunk) -> dict[str, Any]:
    prompt_text = _CHUNK_GATE_PROMPT.format(chunk_text=chunk.text[:4000])
    result = await llm.with_structured_output(ChunkPreparationResult).ainvoke(prompt_text)
    return _structured_dump(result)


async def _prepare_chunk(
    chunk: NarrativeChunk,
    llm: ChatOpenAI,
    semaphore: asyncio.Semaphore,
) -> NarrativeChunk | None:
    async with semaphore:
        try:
            gate_result = await _invoke_chunk_gate(llm, chunk)
        except Exception as e:
            gate_result = {
                "decision": "accept",
                "cleaned_text": chunk.text,
                "quality_score": 0.5,
                "reasoning": f"Chunk gate failed: {e}",
            }

    if gate_result.get("decision") != "accept":
        print(f"  ✗ [{chunk.source_doc}] chunk {chunk.id} rejected before extraction")
        return None

    cleaned_text = str(gate_result.get("cleaned_text", chunk.text)).strip()
    if len(cleaned_text) < 50:
        print(f"  ✗ [{chunk.source_doc}] chunk {chunk.id} too short after cleanup")
        return None

    prepared = NarrativeChunk(
        id=chunk.id,
        text=cleaned_text,
        source_doc=chunk.source_doc,
    )
    print(
        f"  ✓ [{chunk.source_doc}] chunk {chunk.id} prepared "
        f"(q={gate_result.get('quality_score', 0.0):.2f})"
    )
    return prepared


async def prepare_chunks_for_extraction(
    chunks: list[NarrativeChunk], max_concurrent: int = 3
) -> list[NarrativeChunk]:
    llm = _init_llm()
    semaphore = asyncio.Semaphore(max_concurrent)
    prepared = await asyncio.gather(*[_prepare_chunk(chunk, llm, semaphore) for chunk in chunks])
    return [chunk for chunk in prepared if chunk is not None]


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _invoke_stage(llm: ChatOpenAI, stage_key: str, prompt_text: str) -> dict[str, Any]:
    stage_model = _stage_model(stage_key)
    result = await llm.with_structured_output(stage_model).ainvoke(prompt_text)
    return _structured_dump(result)


async def _extract_stage(
    llm: ChatOpenAI,
    chunk: NarrativeChunk,
    stage_key: str,
    semaphore: asyncio.Semaphore,
) -> tuple[str, dict[str, Any]]:
    prompt_text = f"{PROMPT_GUARDRAILS}\n\n{EXTRACTION_PROMPTS[stage_key].format(text=chunk.text)}"
    async with semaphore:
        try:
            data = await _invoke_stage(llm, stage_key, prompt_text)
        except Exception as e:
            print(f"  ✗ {stage_key} failed [{chunk.id}]: {e}")
            data = _empty_stage_payload(stage_key)
            data["notes"] = f"{type(e).__name__}: {e}"
    return stage_key, data


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _invoke_judge(llm: ChatOpenAI, chunk: NarrativeChunk, layers: dict[str, Any]) -> dict[str, Any]:
    avg_confidence = (
        sum(v.get("confidence", 0.0) for v in layers.values() if isinstance(v, dict)) / max(len(layers), 1)
    )
    prompt = f"""You are a strict narrative quality gate.

CHUNK (first 2000 chars):
{chunk.text[:2000]}

EXTRACTION SUMMARY (avg confidence: {avg_confidence:.2f}):
{json.dumps({k: v.get('confidence', 0) for k, v in layers.items()}, ensure_ascii=False)}

Return structured output:
- decision: \"accept\" if the extractions have meaningful content, \"reject\" if the chunk is too short/noise
- reasoning: brief explanation
- quality_score: 0.0-1.0 overall quality"""
    result = await llm.with_structured_output(JudgeOutput).ainvoke(prompt)
    return _structured_dump(result)


async def _extract_chunk(
    chunk: NarrativeChunk,
    llm: ChatOpenAI,
    semaphore: asyncio.Semaphore,
) -> dict[str, Any]:
    stage_results = await asyncio.gather(
        *[_extract_stage(llm, chunk, stage, semaphore) for stage in EXTRACTION_STAGE_ORDER]
    )
    layers = {key: data for key, data in stage_results}

    async with semaphore:
        try:
            judge = await _invoke_judge(llm, chunk, layers)
        except Exception as e:
            judge = {"decision": "accept", "reasoning": f"Judge failed: {e}", "quality_score": 0.5}

    verdict = judge.get("decision", "?")
    score = judge.get("quality_score", 0.0)
    print(f"  ✓ [{chunk.source_doc}] chunk {chunk.id}  →  {verdict}  (q={score:.2f})")
    return {"chunk": chunk, "layers": layers, "judge": judge}


async def run_extraction_pipeline(
    chunks: list[NarrativeChunk], max_concurrent: int = 3
) -> list[dict[str, Any]]:
    llm = _init_llm()
    semaphore = asyncio.Semaphore(max_concurrent)
    results = await asyncio.gather(*[_extract_chunk(chunk, llm, semaphore) for chunk in chunks])
    return list(results)


print("✓ Async extraction functions defined")

✓ Async extraction functions defined


In [20]:
# ── Run extraction pipeline ───────────────────────────────────────────────────
print(
    f"Preparing {len(validated_chunks)} chunks for extraction "
    f"(max_concurrent={CONFIG['max_concurrent_llm']})..."
)

prepared_chunks: list[NarrativeChunk] = asyncio.run(
    prepare_chunks_for_extraction(validated_chunks, max_concurrent=CONFIG["max_concurrent_llm"])
)
print(f"✓ {len(prepared_chunks)}/{len(validated_chunks)} chunks passed chunk preparation")

print(f"Processing {len(prepared_chunks)} prepared chunks...")
extraction_results: list[dict[str, Any]] = asyncio.run(
    run_extraction_pipeline(prepared_chunks, max_concurrent=CONFIG["max_concurrent_llm"])
)

accepted = [result for result in extraction_results if result["judge"].get("decision") == "accept"]
print(f"\n✓ Extraction complete: {len(accepted)}/{len(extraction_results)} chunks accepted")


def _json_text(value: Any) -> str:
    return json.dumps(value if value is not None else {}, ensure_ascii=False)


# ── Store extraction_chunks ───────────────────────────────────────────────────
def store_extraction_chunks(results: list[dict[str, Any]], con: duckdb.DuckDBPyConnection) -> None:
    rows: list[dict[str, Any]] = []
    for item in results:
        chunk: NarrativeChunk = item["chunk"]
        layers: dict[str, Any] = item["layers"]
        judge: dict[str, Any] = item["judge"]
        rows.append(
            {
                "chunk_id": chunk.id,
                "source_doc": chunk.source_doc,
                "text": chunk.text,
                "visual_atmosphere": _json_text(layers.get("visual_atmosphere")),
                "dialogue_style": _json_text(layers.get("dialogue_style")),
                "psychological_profile": _json_text(layers.get("psychological_profile")),
                "power_dynamics": _json_text(layers.get("power_dynamics")),
                "dramatic_structure": _json_text(layers.get("dramatic_structure")),
                "prose_texture": _json_text(layers.get("prose_texture")),
                "emotional_resonance": _json_text(layers.get("emotional_resonance")),
                "judge_decision": judge.get("decision"),
                "judge_reasoning": judge.get("reasoning"),
                "quality_score": judge.get("quality_score", 0.0),
            }
        )

    if not rows:
        print("! No extraction rows to store")
        return

    frame = pd.DataFrame(rows)
    con.register("extraction_chunk_batch", frame)
    try:
        con.execute(
            """
            INSERT OR REPLACE INTO extraction_chunks BY NAME
            SELECT
                chunk_id,
                source_doc,
                text,
                CAST(visual_atmosphere AS JSON) AS visual_atmosphere,
                CAST(dialogue_style AS JSON) AS dialogue_style,
                CAST(psychological_profile AS JSON) AS psychological_profile,
                CAST(power_dynamics AS JSON) AS power_dynamics,
                CAST(dramatic_structure AS JSON) AS dramatic_structure,
                CAST(prose_texture AS JSON) AS prose_texture,
                CAST(emotional_resonance AS JSON) AS emotional_resonance,
                judge_decision,
                judge_reasoning,
                quality_score
            FROM extraction_chunk_batch
            """
        )
    finally:
        con.unregister("extraction_chunk_batch")

    print(f"✓ Stored {len(frame)} extraction chunks")
    con.sql(
        "SELECT judge_decision, COUNT(*) as n, ROUND(AVG(quality_score), 2) as avg_score "
        "FROM extraction_chunks GROUP BY 1 ORDER BY 1"
    ).show()


store_extraction_chunks(extraction_results, con)

Preparing 19 chunks for extraction (max_concurrent=3)...
  ✓ [Blank 4.pdf] chunk Blank 4_0002 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0001 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0000 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0003 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0005 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0004 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0008 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0006 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0007 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0009 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0010 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0011 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0012 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0014 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0013 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0015 prepared (q=0.50)
  ✓ [Blank 4.pdf] chunk Blank 4_0016 prepared (q=0.50)
  ✓ [Bla

In [23]:
# ── Synthesis + Abstraction ───────────────────────────────────────────────────


def _bounded_json_payload(items: list[dict[str, Any]], max_chars: int) -> tuple[str, int]:
    selected: list[dict[str, Any]] = []
    current_size = 2

    for item in items:
        encoded = json.dumps(item, ensure_ascii=False)
        item_size = len(encoded) + (1 if selected else 0)
        if selected and current_size + item_size > max_chars:
            break
        if not selected and current_size + item_size > max_chars:
            selected.append(item)
            break
        selected.append(item)
        current_size += item_size

    return json.dumps(selected, ensure_ascii=False), len(selected)



def _rank_accepted_for_synthesis(accepted_items: list[dict[str, Any]]) -> list[dict[str, Any]]:
    return sorted(
        accepted_items,
        key=lambda item: item["judge"].get("quality_score", 0.0),
        reverse=True,
    )



def _cluster_accepted_items(accepted_items: list[dict[str, Any]]) -> dict[int, list[dict[str, Any]]]:
    if len(accepted_items) <= 1 or AgglomerativeClustering is None:
        return {0: accepted_items}

    texts = [item["chunk"].text for item in accepted_items]
    try:
        embeddings = embedder.embed(texts)
    except Exception as exc:
        print(f"  ! clustering embeddings failed: {exc}")
        return {0: accepted_items}

    if len(embeddings) <= 1:
        return {0: accepted_items}

    try:
        clustering = AgglomerativeClustering(
            n_clusters=None,
            metric="cosine",
            linkage="average",
            distance_threshold=0.35,
        )
        labels = clustering.fit_predict(embeddings)
    except TypeError:
        clustering = AgglomerativeClustering(
            n_clusters=None,
            affinity="cosine",
            linkage="average",
            distance_threshold=0.35,
        )
        labels = clustering.fit_predict(embeddings)
    except Exception as exc:
        print(f"  ! clustering fallback used: {exc}")
        return {0: accepted_items}

    clusters: dict[int, list[dict[str, Any]]] = {}
    for label, item in zip(labels, accepted_items):
        cluster_id = int(label)
        clusters.setdefault(cluster_id, []).append(item)
    return clusters


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _run_synthesis(llm: ChatOpenAI, accepted_items: list[dict[str, Any]]) -> dict[str, Any]:
    """Cross-reference synthesis across all accepted chunks."""
    combined = [
        {"chunk_id": item["chunk"].id, "source_doc": item["chunk"].source_doc, **item["layers"]}
        for item in _rank_accepted_for_synthesis(accepted_items)
    ]
    synthesis_payload, included = _bounded_json_payload(combined, max_chars=40_000)
    print(f"  • Synthesis input bounded to {included}/{len(combined)} chunks")
    prompt = EXTRACTION_PROMPTS["cross_reference_synthesis"].format(extractions=synthesis_payload)
    model = _stage_model("cross_reference_synthesis")
    result = await llm.with_structured_output(model).ainvoke(prompt)
    return _structured_dump(result)


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _run_abstraction(llm: ChatOpenAI, synthesis: dict[str, Any]) -> dict[str, Any]:
    """Generate reusable templates from abstractable patterns."""
    patterns = synthesis.get("abstractable_patterns", [])
    if not patterns:
        print("  ! No abstractable patterns found — skipping abstraction")
        return {"templates": [], "notes": "No patterns to abstract"}

    pattern_payload, included = _bounded_json_payload(patterns, max_chars=24_000)
    print(f"  • Abstraction input bounded to {included}/{len(patterns)} patterns")
    prompt = EXTRACTION_PROMPTS["abstraction_final"].format(patterns=pattern_payload)
    model = _stage_model("abstraction_final")
    result = await llm.with_structured_output(model).ainvoke(prompt)
    return _structured_dump(result)


async def _synthesis_pipeline(accepted_items: list[dict[str, Any]]) -> tuple[dict[str, Any], dict[str, Any]]:
    llm = _init_llm()
    print(f"Running synthesis over {len(accepted_items)} accepted chunks...")

    clusters = _cluster_accepted_items(accepted_items)
    cluster_results: list[dict[str, Any]] = []
    for cluster_id, cluster_items in sorted(clusters.items(), key=lambda item: len(item[1]), reverse=True):
        print(f"  • Synthesizing cluster {cluster_id} with {len(cluster_items)} chunk(s)")
        cluster_synthesis = await _run_synthesis(llm, cluster_items)
        cluster_synthesis["cluster_id"] = cluster_id
        cluster_synthesis["cluster_size"] = len(cluster_items)
        cluster_results.append(cluster_synthesis)

    merged_synthesis = {
        "cluster_results": cluster_results,
        "resonance_patterns": [],
        "character_signatures": [],
        "scene_composition": [],
        "abstractable_patterns": [],
        "generation_seeds": [],
    }
    for cluster_synthesis in cluster_results:
        merged_synthesis["resonance_patterns"].extend(cluster_synthesis.get("resonance_patterns", []))
        merged_synthesis["character_signatures"].extend(cluster_synthesis.get("character_signatures", []))
        merged_synthesis["scene_composition"].extend(cluster_synthesis.get("scene_composition", []))
        merged_synthesis["abstractable_patterns"].extend(cluster_synthesis.get("abstractable_patterns", []))
        merged_synthesis["generation_seeds"].extend(cluster_synthesis.get("generation_seeds", []))

    print(
        f"  ✓ clusters={len(cluster_results)} patterns={len(merged_synthesis['abstractable_patterns'])}"
        f" seeds={len(merged_synthesis['generation_seeds'])}"
    )
    abstraction = await _run_abstraction(llm, merged_synthesis)
    print(f"  ✓ Templates: {len(abstraction.get('templates', []))}")
    return merged_synthesis, abstraction


synthesis_result, abstraction_result = asyncio.run(_synthesis_pipeline(accepted))
print("\n✓ Synthesis + abstraction complete")

Running synthesis over 19 accepted chunks...
Loaded as API: https://chmielvu-multilingual-nlp.hf.space/embeddings/
  ! clustering embeddings failed: Could not fetch config for https://chmielvu-multilingual-nlp.hf.space/embeddings/
  • Synthesizing cluster 0 with 19 chunk(s)
  • Synthesis input bounded to 1/19 chunks
  • Synthesis input bounded to 1/19 chunks
  • Synthesis input bounded to 1/19 chunks


NotFoundError: <!DOCTYPE html><html lang="en"><head><meta charSet="utf-8"/><meta name="viewport" content="minimum-scale=1, initial-scale=1, width=device-width, viewport-fit=cover"/><meta name="viewport" content="width=device-width, initial-scale=1"/><link rel="stylesheet" href="/_next/static/css/2061f151a632d52b.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/4aa34f00c9a735eb.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/8bd2226ccc3cc522.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/68fd0b07afc3d15d.css" data-precedence="next"/><link rel="stylesheet" href="/_next/static/css/c6f80ce875958cc8.css" data-precedence="next"/><link rel="preload" as="script" fetchPriority="low" href="/_next/static/chunks/webpack-eb1a8bf6a10b768e.js"/><script src="/_next/static/chunks/c6e29eda-25a621f962ffa7a1.js" async=""></script><script src="/_next/static/chunks/38260-54573970784b7f1a.js" async=""></script><script src="/_

In [ ]:
# ── LLM-native graph construction ─────────────────────────────────────────────


def _bounded_list(items: list[dict[str, Any]], max_chars: int) -> list[dict[str, Any]]:
    bounded_json, _ = _bounded_json_payload(items, max_chars=max_chars)
    return json.loads(bounded_json)


def _bounded_graph_payload(synthesis: dict[str, Any], abstraction: dict[str, Any], max_chars: int = 60_000) -> str:
    synthesis_trimmed = dict(synthesis)
    abstraction_trimmed = dict(abstraction)

    if isinstance(synthesis_trimmed.get("resonance_patterns"), list):
        synthesis_trimmed["resonance_patterns"] = _bounded_list(synthesis_trimmed["resonance_patterns"], 12_000)
    if isinstance(synthesis_trimmed.get("character_signatures"), list):
        synthesis_trimmed["character_signatures"] = _bounded_list(synthesis_trimmed["character_signatures"], 12_000)
    if isinstance(synthesis_trimmed.get("scene_composition"), list):
        synthesis_trimmed["scene_composition"] = _bounded_list(synthesis_trimmed["scene_composition"], 10_000)
    if isinstance(synthesis_trimmed.get("abstractable_patterns"), list):
        synthesis_trimmed["abstractable_patterns"] = _bounded_list(synthesis_trimmed["abstractable_patterns"], 10_000)
    if isinstance(synthesis_trimmed.get("generation_seeds"), list):
        synthesis_trimmed["generation_seeds"] = _bounded_list(synthesis_trimmed["generation_seeds"], 8_000)
    if isinstance(abstraction_trimmed.get("templates"), list):
        abstraction_trimmed["templates"] = _bounded_list(abstraction_trimmed["templates"], 18_000)

    combined = {"synthesis": synthesis_trimmed, "abstraction": abstraction_trimmed}
    encoded = json.dumps(combined, ensure_ascii=False)
    if len(encoded) <= max_chars:
        return encoded

    if isinstance(abstraction_trimmed.get("templates"), list) and len(abstraction_trimmed["templates"]) > 1:
        abstraction_trimmed["templates"] = abstraction_trimmed["templates"][: max(1, len(abstraction_trimmed["templates"]) // 2)]

    combined = {"synthesis": synthesis_trimmed, "abstraction": abstraction_trimmed}
    return json.dumps(combined, ensure_ascii=False)


@retry(
    retry=retry_if_exception_type(Exception),
    stop=stop_after_attempt(3),
    wait=wait_exponential(multiplier=1, min=2, max=10),
    reraise=True,
)
async def _construct_graph(
    synthesis: dict[str, Any], abstraction: dict[str, Any], llm: ChatOpenAI
) -> LLMGraphOutput:
    prompt = GRAPH_CONSTRUCTION_PROMPT.format(
        synthesis_json=_bounded_graph_payload(synthesis, abstraction, max_chars=60_000)
    )
    result = await llm.with_structured_output(LLMGraphOutput).ainvoke(prompt)
    if isinstance(result, LLMGraphOutput):
        return result
    return LLMGraphOutput.model_validate(result)


print("Constructing inspiration graph via LLM...")
graph_output: LLMGraphOutput = asyncio.run(
    _construct_graph(synthesis_result, abstraction_result, _init_llm())
)

print(
    f"✓ Graph: {len(graph_output.nodes)} nodes, {len(graph_output.edges)} edges, "
    f"{len(graph_output.entity_resolutions)} entity resolutions"
)

for node in graph_output.nodes[:5]:
    print(f"  [{node.node_type.value:24s}] {node.name}")

In [ ]:
# ── Store graph nodes and edges to DuckDB ─────────────────────────────────────

EDGE_CONFIDENCE_THRESHOLD = 0.75


def store_graph(graph: LLMGraphOutput, con: duckdb.DuckDBPyConnection) -> None:
    node_rows = [
        {
            "node_id": node.node_id,
            "node_type": node.node_type.value,
            "name": node.name,
            "description": node.description,
            "searchable_text": node.searchable_text,
            "properties": json.dumps(node.properties, ensure_ascii=False),
            "pattern_type": node.properties.get("pattern_type", ""),
            "confidence": node.confidence,
        }
        for node in graph.nodes
    ]

    if node_rows:
        node_frame = pd.DataFrame(node_rows)
        con.register("graph_nodes_batch", node_frame)
        try:
            con.execute(
                """
                INSERT OR REPLACE INTO inspiration_nodes BY NAME
                SELECT
                    node_id,
                    node_type,
                    name,
                    description,
                    searchable_text,
                    CAST(properties AS JSON) AS properties,
                    pattern_type,
                    confidence
                FROM graph_nodes_batch
                """
            )
        finally:
            con.unregister("graph_nodes_batch")

    node_ids = {node.node_id for node in graph.nodes}
    edge_rows = []
    skipped = 0
    for edge in graph.edges:
        confidence = float(getattr(edge, "confidence", edge.weight))
        if edge.source_node_id not in node_ids or edge.target_node_id not in node_ids:
            skipped += 1
            continue
        if confidence < EDGE_CONFIDENCE_THRESHOLD or edge.weight < EDGE_CONFIDENCE_THRESHOLD:
            skipped += 1
            continue
        edge_rows.append(
            {
                "edge_id": f"{edge.source_node_id}__{edge.edge_type.value}__{edge.target_node_id}",
                "source_node_id": edge.source_node_id,
                "target_node_id": edge.target_node_id,
                "edge_type": edge.edge_type.value,
                "weight": edge.weight,
                "confidence": confidence,
                "context": edge.context,
            }
        )

    if edge_rows:
        edge_frame = pd.DataFrame(edge_rows)
        con.register("graph_edges_batch", edge_frame)
        try:
            con.execute(
                """
                INSERT OR REPLACE INTO inspiration_edges BY NAME
                SELECT
                    edge_id,
                    source_node_id,
                    target_node_id,
                    edge_type,
                    weight,
                    confidence,
                    context
                FROM graph_edges_batch
                """
            )
        finally:
            con.unregister("graph_edges_batch")

    print(
        f"✓ Stored {len(node_rows)} nodes, {len(edge_rows)} edges"
        f"  ({skipped} edges skipped — confidence or dangling refs)"
    )
    con.sql(
        "SELECT node_type, COUNT(*) as n FROM inspiration_nodes GROUP BY 1 ORDER BY n DESC"
    ).show()
    con.sql(
        "SELECT edge_type, COUNT(*) as n FROM inspiration_edges GROUP BY 1 ORDER BY n DESC"
    ).show()


store_graph(graph_output, con)

In [ ]:
# ── Generate BGE-M3 embeddings (1024-dim) + HNSW index ───────────────────────

to_embed = con.sql(
    "SELECT node_id, searchable_text FROM inspiration_nodes "
    "WHERE embedding IS NULL AND searchable_text IS NOT NULL AND searchable_text != ''"
).fetchall()

if to_embed:
    ids = [row[0] for row in to_embed]
    texts = [row[1] for row in to_embed]

    BATCH_SIZE = 32
    all_embeddings: list[list[float]] = []
    for start in tqdm(range(0, len(texts), BATCH_SIZE), desc="Embedding batches"):
        batch_embs = embedder.embed(texts[start : start + BATCH_SIZE])
        all_embeddings.extend(batch_embs)

    update_frame = pd.DataFrame({"node_id": ids, "embedding": all_embeddings})
    con.register("embedding_updates", update_frame)
    try:
        con.execute(
            """
            UPDATE inspiration_nodes AS target
            SET embedding = src.embedding
            FROM embedding_updates AS src
            WHERE target.node_id = src.node_id
            """
        )
    finally:
        con.unregister("embedding_updates")
    print(f"✓ Embeddings stored for {len(ids)} nodes")
else:
    print("All nodes already have embeddings")

try:
    con.sql(f"""
        CREATE INDEX IF NOT EXISTS idx_inodes_hnsw
        ON inspiration_nodes USING HNSW (embedding)
        WITH (metric = 'cosine', ef_construction = 256, M = 16);
    """)
    print("✓ HNSW index created")
except Exception as e:
    print(f"  ! HNSW index skipped: {e}")

In [ ]:
# ── FTS index + query examples (VSS · FTS · PGQ) ─────────────────────────────

# Build FTS index
try:
    con.sql(
        "PRAGMA create_fts_index('inspiration_nodes', 'node_id', "
        "'name', 'description', 'searchable_text', overwrite=1);"
    )
    print("✓ FTS index created")
except Exception as e:
    print(f"  ! FTS index: {e}")

# ── VSS: vector similarity search ─────────────────────────────────────────────
print("\n=== VSS  (replace query_text to run) ===")
# To run: uncomment and set query_text
# query_text = "power manipulation control hierarchy"
# query_vec  = embedder.embed_single(query_text)
# vss_df = con.execute("""
#     SELECT node_id, node_type, name,
#            array_cosine_similarity(embedding, $1::FLOAT[1024]) AS score
#     FROM inspiration_nodes
#     WHERE embedding IS NOT NULL
#     ORDER BY score DESC LIMIT 10
# """, [query_vec]).fetchdf()
# display(vss_df)

# ── FTS: BM25 full-text search ────────────────────────────────────────────────
print("\n=== FTS (BM25) ===")
try:
    fts_df = con.sql("""
        SELECT node_id, node_type, name, score
        FROM (
            SELECT *, fts_main_inspiration_nodes.match_bm25(node_id, 'power control') AS score
            FROM inspiration_nodes
        ) t
        WHERE score IS NOT NULL
        ORDER BY score DESC
        LIMIT 10
    """).df()
    print(fts_df.to_string() if not fts_df.empty else "  (no FTS results)")
except Exception as e:
    print(f"  FTS query: {e}")

# ── PGQ: property graph pattern matching ──────────────────────────────────────
if PGQ_AVAILABLE:
    print("\n=== PGQ graph traversal ===")
    try:
        con.sql("""
            CREATE PROPERTY GRAPH IF NOT EXISTS inspiration_graph
                VERTEX TABLES (
                    inspiration_nodes
                )
                EDGE TABLES (
                    inspiration_edges
                        SOURCE KEY (source_node_id) REFERENCES inspiration_nodes(node_id)
                        DESTINATION KEY (target_node_id) REFERENCES inspiration_nodes(node_id)
                );
        """)
        pgq_df = con.sql("""
            FROM GRAPH_TABLE(inspiration_graph
                MATCH (a:inspiration_nodes)-[e:inspiration_edges]->(b:inspiration_nodes)
                COLUMNS (a.name AS source, e.edge_type, b.name AS target, e.weight)
            )
            ORDER BY weight DESC LIMIT 20;
        """).df()
        print(pgq_df.to_string() if not pgq_df.empty else "  (no edges yet)")
    except Exception as e:
        print(f"  PGQ: {e}")
else:
    print("\n=== PGQ unavailable (duckpgq not installed) ===")


In [ ]:
# ── Parquet export ────────────────────────────────────────────────────────────
import pandas as pd

parquet_dir = Path(CONFIG["parquet_dir"])
parquet_dir.mkdir(parents=True, exist_ok=True)

_exports = {
    "inspiration_nodes": (
        "SELECT node_id, node_type, name, description, searchable_text, "
        "properties, pattern_type, confidence FROM inspiration_nodes"
    ),
    "inspiration_edges": "SELECT * FROM inspiration_edges",
    "extraction_chunks": (
        "SELECT chunk_id, source_doc, judge_decision, quality_score, "
        "visual_atmosphere, dialogue_style, psychological_profile, "
        "power_dynamics, dramatic_structure, prose_texture, emotional_resonance "
        "FROM extraction_chunks"
    ),
}

for table_name, query in _exports.items():
    df = con.sql(query).df()
    out_path = parquet_dir / f"{table_name}.parquet"
    df.to_parquet(str(out_path), index=False)
    print(f"  ✓ {table_name:30s} → {out_path}  ({len(df)} rows)")

print(f"\n✓ Parquet export complete → {parquet_dir.resolve()}")
print("\n=== Final database summary ===")
con.sql("SELECT 'inspiration_nodes' AS tbl, COUNT(*) AS n FROM inspiration_nodes "
        "UNION ALL SELECT 'inspiration_edges', COUNT(*) FROM inspiration_edges "
        "UNION ALL SELECT 'extraction_chunks', COUNT(*) FROM extraction_chunks").show()